<a href="https://colab.research.google.com/github/Sorya-ly/Khmer_History_retrieval_argumented_generation/blob/embedding_finetune/embedding_finetune_908chunks.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# Part 2 - Embedding, Fine-tuning and Storage
### 41 articles, 908 chunks

Run order: sections 1-5 need no questions and produce the storage deliverable.
Sections 6 onward need `gold.csv` and `gold_test_paraphrased.csv`.

Files this notebook expects beside it:

    khmer_history_chunks.json       khmer_history_train.json
    khmer_history_test.json         gold_draft.csv
    gold_test_paraphrased.csv       gold_review_flags.csv

In [ ]:
import os
print(os.getcwd())
print(sorted(os.listdir()))

/content
['.config', 'sample_data']


In [ ]:
from google.colab import files
files.upload()

Saving gold_draft.csv to gold_draft.csv
Saving gold_review_flags.csv to gold_review_flags.csv
Saving gold_test_paraphrased.csv to gold_test_paraphrased.csv
Saving khmer_history_chunks.json to khmer_history_chunks.json
Saving khmer_history_test.json to khmer_history_test.json
Saving khmer_history_train.json to khmer_history_train.json


{'gold_draft.csv': b'\xef\xbb\xbfchunk_id,question,split,keep,passage_preview\r\nkm-hist-061-00,\xe1\x9e\x8f\xe1\x9e\xbe\xe1\x9e\x96\xe1\x9f\x92\xe1\x9e\x9a\xe1\x9f\x87\xe1\x9e\x9a\xe1\x9e\xb6\xe1\x9e\x87\xe1\x9e\xb6\xe1\x9e\x81\xe1\x9f\x92\xe1\x9e\x98\xe1\x9f\x82\xe1\x9e\x9a\xe1\x9e\x93\xe1\x9f\x85\xe1\x9e\x9f\xe1\x9e\x98\xe1\x9f\x90\xe1\x9e\x99\xe1\x9e\xa2\xe1\x9e\x84\xe1\x9f\x92\xe1\x9e\x82\xe1\x9e\x9a\xe1\x9e\x80\xe1\x9e\xb6\xe1\x9e\x93\xe1\x9f\x8b\xe1\x9e\x9f\xe1\x9e\xb6\xe1\x9e\x9f\xe1\x9e\x93\xe1\x9e\xb6\xe1\x9e\xa2\xe1\x9f\x92\xe1\x9e\x9c\xe1\x9e\xb8\xe1\x9e\x81\xe1\x9f\x92\xe1\x9e\x9b\xe1\x9f\x87?,test,,\xe1\x9e\x93\xe1\x9f\x85\xe1\x9e\x9f\xe1\x9e\x98\xe1\x9f\x90\xe1\x9e\x99\xe1\x9e\xa2\xe1\x9e\x84\xe1\x9f\x92\xe1\x9e\x82\xe1\x9e\x9a \xe1\x9e\x9f\xe1\x9e\xb6\xe1\x9e\x9f\xe1\x9e\x93\xe1\x9e\xb6\xe1\x9e\x98\xe1\x9e\xb6\xe1\x9e\x93\xe1\x9e\x98\xe1\x9e\xbb\xe1\x9e\x81\xe1\x9e\x84\xe1\x9e\xb6\xe1\x9e\x9a\xe1\x9e\x99\xe1\x9f\x89\xe1\x9e\xb6\xe1\x9e\x84\xe1\x9e\x9f\xe1\x9f\x86\xe1\x9

## 1. Setup

In [ ]:
import sys
!{sys.executable} -m pip install -q "sentence-transformers>=3.0" "accelerate>=1.1.0" rank_bm25 khmer-nltk pandas matplotlib

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 7.0/7.0 MB 20.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.2/1.2 MB 76.9 MB/s eta 0:00:00


In [ ]:
import os, json, time, hashlib, random
os.environ["PYTORCH_ENABLE_MPS_FALLBACK"] = "1"

import torch, numpy as np, pandas as pd

SEED = 42
random.seed(SEED); np.random.seed(SEED); torch.manual_seed(SEED)

if torch.cuda.is_available():
    DEVICE = "cuda"
elif torch.backends.mps.is_available():
    DEVICE = "mps"
else:
    DEVICE = "cpu"

BASELINE_MODEL = "BAAI/bge-m3"                      # 568M, zero-shot reference
TRAIN_MODEL    = "intfloat/multilingual-e5-small"   # 118M, the one we fine-tune
TOP_K = 5

print("device:", DEVICE)
if DEVICE == "cpu":
    print("WARNING: encoding 908 chunks with BGE-M3 on CPU takes over an hour.")

device: cuda


## 2. Load chunks, and invalidate stale caches

`cached()` only checks whether the `.npy` file exists - not whether the chunks
changed. The corpus grew from 78 to 908, so any cache from the earlier run holds
vectors for different text. Row 5 of the matrix would no longer describe chunk 5
and retrieval would return confident nonsense with no error. The fingerprint
below removes the caches whenever the chunk set changes.

In [ ]:
chunks_all   = json.load(open("khmer_history_chunks.json", encoding="utf-8"))
train_chunks = json.load(open("khmer_history_train.json", encoding="utf-8"))
test_chunks  = json.load(open("khmer_history_test.json", encoding="utf-8"))

texts = [c["text_for_embedding"] for c in chunks_all]
ids   = [c["chunk_id"] for c in chunks_all]
id_to_index = {cid: i for i, cid in enumerate(ids)}

assert len(set(ids)) == len(ids), "duplicate chunk_id"
assert all(c["chunk_id"] in id_to_index for c in test_chunks), \
    "test chunk missing from the index - its questions would be unanswerable"

# --- cache fingerprint ---
sig  = hashlib.md5("".join(ids).encode()).hexdigest()[:8]
prev = open("chunks.sig").read().strip() if os.path.exists("chunks.sig") else None
if prev != sig:
    for f in ("emb_e5.npy", "emb_bge.npy", "emb_ft.npy"):
        if os.path.exists(f):
            os.remove(f); print("removed stale", f)
open("chunks.sig", "w").write(sig)

pages = {c["metadata"]["page_title"] for c in chunks_all}
print(f"index {len(chunks_all)} chunks from {len(pages)} articles")
print(f"train {len(train_chunks)} | test {len(test_chunks)}")
print(f"top-{TOP_K} is {TOP_K / len(chunks_all):.2%} of the corpus")

index 908 chunks from 41 articles
train 694 | test 173
top-5 is 0.55% of the corpus


## 3. Encode

In [ ]:
from sentence_transformers import SentenceTransformer

def cached(path, fn):
    """Encode once, reuse afterwards. Section 2 clears these when chunks change."""
    if os.path.exists(path):
        arr = np.load(path)
        assert arr.shape[0] == len(texts), f"{path} has {arr.shape[0]} rows, expected {len(texts)}"
        print(f"loaded {path}  {arr.shape}")
        return arr
    t0 = time.time()
    arr = fn()
    np.save(path, arr)
    print(f"{path}  {arr.shape}  {time.time() - t0:.0f}s")
    return arr

In [ ]:
# e5 requires these exact prefixes - without them the model is noticeably worse
E5_Q, E5_P = "query: ", "passage: "

e5 = SentenceTransformer(TRAIN_MODEL, device=DEVICE)

emb_e5 = cached("emb_e5.npy", lambda: e5.encode(
    [E5_P + t for t in texts], batch_size=32,
    normalize_embeddings=True, show_progress_bar=True))

In [ ]:
# The slow cell: 568M parameters over 908 chunks.
# ~10 min on a T4, over an hour on CPU. Runs once, then loads from disk.
bge = SentenceTransformer(BASELINE_MODEL, device=DEVICE)
bge.max_seq_length = 512          # default is 8192; our longest chunk is ~460 tokens

emb_bge = cached("emb_bge.npy", lambda: bge.encode(
    texts, batch_size=8,
    normalize_embeddings=True, show_progress_bar=True))

## 4. Search

In [ ]:
def dense_search(model, matrix, query, k=TOP_K, prefix=""):
    """Vectors are unit-normalised, so a dot product IS cosine similarity."""
    q = model.encode([prefix + query], normalize_embeddings=True)[0]
    scores = matrix @ q
    top = np.argpartition(-scores, k)[:k]          # 908 chunks - avoid a full sort
    top = top[np.argsort(-scores[top])]
    return [(ids[i], float(scores[i])) for i in top]

search_e5  = lambda q, k=TOP_K: dense_search(e5,  emb_e5,  q, k, E5_Q)
search_bge = lambda q, k=TOP_K: dense_search(bge, emb_bge, q, k)

In [ ]:
from rank_bm25 import BM25Okapi
from khmernltk import word_tokenize

# Khmer has no spaces, so BM25 needs a real tokenizer. Adjacent-token bigrams are
# added because the segmenter splits multi-word proper nouns (បន្ទាយឆ្មារ ->
# បន្ទាយ + ឆ្មារ), which destroys exactly the precision BM25 is good at.
STOP = {"និង", "នៅ", "ជា", "នៃ", "ដែល", "នេះ", "មួយ", "ក៏", "ភាព", "ការ",
        "របស់", "បាន", "ទៅ", "ពី", "ពេល", "មក", "។", " ", ""}

def km_tokens(text):
    toks = [w for w in word_tokenize(text) if w.strip() and w not in STOP]
    return toks + [f"{a}_{b}" for a, b in zip(toks, toks[1:])]

t0 = time.time()
bm25 = BM25Okapi([km_tokens(c["text_payload"]) for c in chunks_all])
print(f"BM25 index built in {time.time() - t0:.0f}s")   # khmercut is CPU-bound, ~4 min

def search_bm25(query, k=TOP_K):
    scores = bm25.get_scores(km_tokens(query))
    top = np.argsort(-scores)[:k]
    return [(ids[i], float(scores[i])) for i in top]

In [ ]:
q = "របបខ្មែរក្រហមគ្រប់គ្រងកម្ពុជាពីពេលណា?"   # when did the Khmer Rouge take power?

for name, fn in [("bm25", search_bm25), ("e5", search_e5), ("bge", search_bge)]:
    cid, score = fn(q)[0]
    c = chunks_all[id_to_index[cid]]
    print(f"{name:5} {cid}  {score:.3f}  [{c['metadata']['page_title'][:22]}]  "
          f"{c['text_payload'][:55]}")

## 5. Store  <- the deliverable, runs without any questions

In [ ]:
def write_store(matrix, model_name, q_prefix, p_prefix):
    store = {
        "model": model_name,
        "dim": int(matrix.shape[1]),
        "normalized": True,
        "query_prefix": q_prefix,
        "passage_prefix": p_prefix,
        "n_chunks": len(chunks_all),
        "chunks": [{"chunk_id": c["chunk_id"],
                    "text_payload": c["text_payload"],
                    "metadata": c["metadata"]} for c in chunks_all],
    }
    json.dump(store, open("rag_store.json", "w", encoding="utf-8"),
              ensure_ascii=False, indent=1)
    np.save("emb_final.npy", matrix)
    print(f"rag_store.json + emb_final.npy  ({model_name}, {matrix.shape})")

# BGE-M3 is the recommended retriever and needs no prefixes.
write_store(emb_bge, BASELINE_MODEL, "", "")

---
## 6. The question set

`gold.csv` holds `chunk_id,question`. Each question is routed to train or test by
**which split its chunk is in** - never pooled and re-split randomly, or test
passages leak into training.

In [ ]:
import pandas as pd
if not os.path.exists("gold.csv"):
    g = pd.read_csv("gold_draft.csv", encoding="utf-8-sig")
    g[["chunk_id", "question"]].to_csv("gold.csv", index=False, encoding="utf-8")
    print(f"wrote gold.csv ({len(g)} questions)")
else:
    print("gold.csv already exists")

In [ ]:
gold = pd.read_csv("gold.csv")
gold["chunk_id"] = gold["chunk_id"].str.strip()
gold["question"] = gold["question"].str.strip()

bad = set(gold["chunk_id"]) - set(ids)
assert not bad, f"unknown chunk_id (stale after re-chunking?): {sorted(bad)[:5]}"

train_ids = {c["chunk_id"] for c in train_chunks}
test_ids  = {c["chunk_id"] for c in test_chunks}

gold_train = gold[gold["chunk_id"].isin(train_ids)].reset_index(drop=True)
gold_test  = gold[gold["chunk_id"].isin(test_ids)].reset_index(drop=True)

print(f"{len(gold)} questions -> train {len(gold_train)} | test {len(gold_test)}")
print(f"chunks covered: {gold['chunk_id'].nunique()} / {len(ids)}")
assert len(gold_train) >= 100, "too few training pairs"
assert len(gold_test)  >= 40,  "too few test questions"

## 7. Fine-tune

In [ ]:
from sentence_transformers import InputExample, losses
from torch.utils.data import DataLoader

payload = {c["chunk_id"]: c["text_for_embedding"] for c in chunks_all}

examples = [InputExample(texts=[E5_Q + r.question, E5_P + payload[r.chunk_id]])
            for r in gold_train.itertuples()]

BATCH = 32   # MultipleNegativesRankingLoss uses the other 31 passages in the batch
             # as negatives, so a bigger batch is a harder and better training task
loader = DataLoader(examples, shuffle=True, batch_size=BATCH, drop_last=True)
print(f"{len(examples)} pairs | {len(loader)} batches/epoch | {len(loader)*3} steps over 3 epochs")

model = SentenceTransformer(TRAIN_MODEL, device=DEVICE)
loss  = losses.MultipleNegativesRankingLoss(model)

model.fit(train_objectives=[(loader, loss)],
          epochs=3,
          warmup_steps=int(0.1 * len(loader) * 3),
          optimizer_params={"lr": 2e-5},
          use_amp=torch.cuda.is_available(),   # mixed precision breaks on Apple MPS
          output_path="khmer-retriever-finetuned",
          show_progress_bar=True)
print("saved -> khmer-retriever-finetuned")

In [ ]:
ft = SentenceTransformer("khmer-retriever-finetuned", device=DEVICE)
emb_ft = ft.encode([E5_P + t for t in texts], batch_size=32,
                   normalize_embeddings=True, show_progress_bar=True)
np.save("emb_ft.npy", emb_ft)
search_ft = lambda q, k=TOP_K: dense_search(ft, emb_ft, q, k, E5_Q)

## 8. Evaluate

In [ ]:
def evaluate(search_fn, df, k=10):
    """Recall@n = share of questions whose gold chunk is in the top n.
       MRR@k    = 1/rank of the gold chunk, averaged (0 if outside the top k)."""
    ranks = []
    for r in df.itertuples():
        got = [cid for cid, _ in search_fn(r.question, k)]
        ranks.append(got.index(r.chunk_id) + 1 if r.chunk_id in got else 999)
    ranks = np.array(ranks)
    return {"Recall@1": float((ranks == 1).mean()),
            "Recall@3": float((ranks <= 3).mean()),
            "Recall@5": float((ranks <= 5).mean()),
            "MRR@10":   float(np.where(ranks <= k, 1 / ranks, 0).mean()),
            "n": len(df)}


def make_hybrid(dense_fn, c=60):
    """Reciprocal rank fusion: merge by rank position, not score, because BM25
    scores and cosine scores are on incomparable scales."""
    def f(query, k=TOP_K):
        fused = {}
        for fn in (search_bm25, dense_fn):
            for rank, (cid, _) in enumerate(fn(query, 20)):
                fused[cid] = fused.get(cid, 0) + 1 / (c + rank + 1)
        return sorted(fused.items(), key=lambda x: -x[1])[:k]
    return f


systems = {
    "BM25 (lexical)":           search_bm25,
    "e5-small (zero-shot)":     search_e5,
    "BGE-M3 (zero-shot)":       search_bge,
    "e5-small (fine-tuned)":    search_ft,
    "Hybrid (BM25 + fine-tuned)": make_hybrid(search_ft),
    "Hybrid (BM25 + BGE-M3)":   make_hybrid(search_bge),
}

results = pd.DataFrame({k: evaluate(f, gold_test) for k, f in systems.items()}).T
display(results.round(3))
results.round(4).to_csv("results_original.csv", encoding="utf-8-sig")

---
## 9. Vocabulary-mismatch test  <- the main experiment

The questions were drafted by reading each passage, so they reuse that passage's
words - which is what BM25 scores on. `gold_test_paraphrased.csv` asks the same
questions about the same chunks, worded differently.

Nothing about the task changes; only the overlap between question and passage
changes. Whatever a system loses here is what it was getting from word matching
rather than from meaning.

In [ ]:
para = pd.read_csv("gold_test_paraphrased.csv", encoding="utf-8-sig")
assert set(para["chunk_id"]) <= set(ids), "paraphrase file is stale - chunk_ids changed"
print(f"{len(para)} paraphrased questions over {para['chunk_id'].nunique()} chunks\n")
for r in para.head(3).itertuples():
    print(f"  original: {r.original_question}")
    print(f"  reworded: {r.question}\n")

In [ ]:
para_r = pd.DataFrame({k: evaluate(f, para) for k, f in systems.items()}).T

cmp = pd.DataFrame({
    "R@1 original":    results["Recall@1"],
    "R@1 paraphrased": para_r["Recall@1"],
    "R@1 drop":        results["Recall@1"] - para_r["Recall@1"],
    "MRR original":    results["MRR@10"],
    "MRR paraphrased": para_r["MRR@10"],
    "MRR drop":        results["MRR@10"] - para_r["MRR@10"],
}).round(3)
display(cmp)
cmp.to_csv("results_comparison.csv", encoding="utf-8-sig")

print("\nRead the DROP column, not the absolute scores.")
print("Large drop = the system was relying on literal word overlap.")
print("Small drop = it was matching on meaning.")

In [ ]:
import matplotlib.pyplot as plt

fig, ax = plt.subplots(figsize=(9, 4))
x = np.arange(len(cmp)); w = 0.38
ax.bar(x - w/2, cmp["R@1 original"],    w, label="original wording", color="#2a78d6")
ax.bar(x + w/2, cmp["R@1 paraphrased"], w, label="paraphrased",      color="#eb6834")
ax.set_xticks(x); ax.set_xticklabels(cmp.index, rotation=18, ha="right", fontsize=8)
ax.set_ylabel("Recall@1"); ax.set_ylim(0, 1)
ax.set_title(f"Robustness to vocabulary mismatch  (n={len(para)}, {len(chunks_all)} chunks)")
ax.legend(frameon=False)
for s in ("top", "right"): ax.spines[s].set_visible(False)
plt.tight_layout(); plt.savefig("results_paraphrase.png", dpi=200); plt.show()

In [ ]:
# Which questions fine-tuning moved, on the set where it matters
rows = []
for r in para.itertuples():
    def rank(fn):
        got = [cid for cid, _ in fn(r.question, 20)]
        return got.index(r.chunk_id) + 1 if r.chunk_id in got else 99
    before, after = rank(search_e5), rank(search_ft)
    if before != after:
        rows.append({"question": r.question[:45], "before": before,
                     "after": after, "change": before - after})

moved = pd.DataFrame(rows).sort_values("change", ascending=False)
print(f"improved {(moved['change'] > 0).sum()} | worse {(moved['change'] < 0).sum()}")
display(moved.head(12))

---
## 10. How many epochs?

Trains one epoch at a time and evaluates after each. Validation questions are
held out of **training**, not taken from the test set - tuning on `gold_test`
would make the final numbers meaningless.

In [ ]:
val = gold_train.sample(frac=0.15, random_state=SEED)
tr  = gold_train.drop(val.index)
print(f"train {len(tr)} | val {len(val)} | test {len(gold_test)} (untouched)")

ex = [InputExample(texts=[E5_Q + r.question, E5_P + payload[r.chunk_id]])
      for r in tr.itertuples()]
sweep_loader = DataLoader(ex, shuffle=True, batch_size=32, drop_last=True)
print(f"{len(sweep_loader)} batches per epoch")

In [ ]:
sweep = SentenceTransformer(TRAIN_MODEL, device=DEVICE)
sloss = losses.MultipleNegativesRankingLoss(sweep)
history, best = [], -1

for ep in range(1, 9):
    sweep.fit(train_objectives=[(sweep_loader, sloss)], epochs=1,
              warmup_steps=int(0.1 * len(sweep_loader)) if ep == 1 else 0,
              optimizer_params={"lr": 2e-5},
              use_amp=torch.cuda.is_available(), show_progress_bar=False)

    emb = sweep.encode([E5_P + t for t in texts], batch_size=32,
                       normalize_embeddings=True)
    m = evaluate(lambda q, k=10: dense_search(sweep, emb, q, k, E5_Q), val)
    m["epoch"] = ep; history.append(m)
    mark = ""
    if m["MRR@10"] > best:
        best = m["MRR@10"]; sweep.save("khmer-retriever-best"); mark = "  <- best, saved"
    print(f"epoch {ep}:  R@1 {m['Recall@1']:.3f}   MRR {m['MRR@10']:.3f}{mark}")

hist = pd.DataFrame(history).set_index("epoch")
hist[["Recall@1", "MRR@10"]].plot(marker="o", figsize=(7, 4), ylim=(0, 1),
                                  title="Validation score per epoch")
plt.tight_layout(); plt.savefig("results_epochs.png", dpi=200); plt.show()
display(hist.round(3))

Rising then flattening then falling: the peak is your epoch count. Still
climbing at 8 means undertrained - extend the range. Falling after epoch 2 means
overfitting - drop the learning rate to `1e-5` first.

The schedule restarts on each `fit()` call, so this is not identical to one
continuous run. Fine for choosing an epoch count; worth a footnote if plotted in
the report.

In [ ]:
# Promote the best checkpoint, then measure on the test set ONCE.
ft = SentenceTransformer("khmer-retriever-best", device=DEVICE)
emb_ft = ft.encode([E5_P + t for t in texts], batch_size=32,
                   normalize_embeddings=True, show_progress_bar=True)
np.save("emb_ft.npy", emb_ft)
search_ft = lambda q, k=TOP_K: dense_search(ft, emb_ft, q, k, E5_Q)

print("original :", {k: round(v, 3) for k, v in evaluate(search_ft, gold_test).items()})
print("reworded :", {k: round(v, 3) for k, v in evaluate(search_ft, para).items()})

---
## 11. Cleaning the gold set

`gold_review_flags.csv` lists questions where another chunk is a near-equal
lexical match. Compare `gold_preview` against `rival_preview`, mark `drop` with
`y` where both genuinely answer the question, then re-run from section 6.

In [ ]:
flags = pd.read_csv("gold_review_flags.csv", encoding="utf-8-sig")
if "drop" in flags.columns and flags["drop"].notna().any():
    d = flags[flags["drop"].astype(str).str.lower() == "y"]
    bad = set(zip(d["chunk_id"], d["question"]))
    g = pd.read_csv("gold.csv")
    keep = ~g.apply(lambda r: (r["chunk_id"], r["question"]) in bad, axis=1)
    g[keep].to_csv("gold.csv", index=False, encoding="utf-8")
    print(f"dropped {(~keep).sum()}, kept {keep.sum()} - re-run from section 6")
else:
    print(f"{len(flags)} flagged questions awaiting review.")
    display(flags[["chunk_id", "rival", "rank", "margin", "question"]].head(10))

---
## 12. Final storage for Part 3

In [ ]:
# Primary: BGE-M3, the recommended retriever. No prefixes.
write_store(emb_bge, BASELINE_MODEL, "", "")
np.save("emb_finetuned.npy", emb_ft)      # secondary artifact

readme = f"""# Part 2 output -> Part 3

rag_store.json      {len(chunks_all)} chunks: chunk_id, text_payload, metadata, in vector order
emb_final.npy       {emb_bge.shape[0]} x {emb_bge.shape[1]}, unit-normalised, BAAI/bge-m3  <- USE THIS
emb_finetuned.npy   {emb_ft.shape[0]} x {emb_ft.shape[1]}, fine-tuned e5-small (secondary)
results_*.csv       evaluation tables
results_*.png       figures

RECOMMENDED RETRIEVER: BAAI/bge-m3, zero-shot.
It was the most robust system under reworded questions. BGE-M3 takes NO query or
passage prefix. Adding e5's "query: " prefix degrades retrieval silently.

    import json, numpy as np
    from sentence_transformers import SentenceTransformer

    store = json.load(open("rag_store.json", encoding="utf-8"))
    emb   = np.load("emb_final.npy")
    model = SentenceTransformer("BAAI/bge-m3")

    q   = model.encode([question], normalize_embeddings=True)[0]
    top = np.argsort(-(emb @ q))[:5]
    passages = [store["chunks"][i] for i in top]

Vectors are unit-normalised, so the dot product is cosine similarity.

WARNING: rag_store.json and emb_final.npy are coupled by ROW ORDER.
emb_final[i] is the vector for store["chunks"][i]. Nothing enforces this - if you
sort or filter the chunk list without reindexing the matrix, every vector points
at the wrong passage and retrieval fails silently.
"""
open("PART3_README.md", "w", encoding="utf-8").write(readme)
print(readme)

---
## 13. Corpus-size comparison

The same experiment was run on a 78-chunk corpus (1 article) before expanding to
908 chunks (41 articles). If the earlier results are in `run_78chunks/`, this
compares them - a widening gap between lexical and dense retrieval as the corpus
grows is a stronger claim than either run alone.

In [ ]:
old = "run_78chunks/results_comparison.csv"
if os.path.exists(old):
    o = pd.read_csv(old, index_col=0)
    both = pd.DataFrame({
        "R@1 (78 chunks)":  o["R@1 original"],
        "R@1 (908 chunks)": cmp["R@1 original"],
        "drop 78":          o["R@1 drop"],
        "drop 908":         cmp["R@1 drop"],
    }).round(3)
    display(both)
else:
    print("run_78chunks/results_comparison.csv not found - skipping")